# Множество решений двуслойной модели боковых сборок

**Эксперимент:** Георг, Scorpion v2, МГТУ, 05.10.2026; зондирование 100 кГц.
**Статус:** исследовательский расчёт с кандидатными дыхательными интервалами.
Индивидуальные электрические параметры и функции сердца пока не валидированы.

Сначала следует просмотреть [электроды и сигналы эксперимента](10.00_Эксперимент_и_сигналы_Георгия_Scorpion_v2.html),
затем [настройки регистрации](10.20_Настройки_и_бинарные_потоки_Scorpion_v2.md)
и [происхождение разметки](11.20_Просмотр_и_разметка_Scorpion_v2.md).
Этот ноутбук проверяет, насколько измеренные уровни совместимы с плоской
двуслойной моделью при ограниченных сопротивлениях тканей.

In [1]:
from IPython.display import display, HTML
from build_lateral_solution_surfaces_report import verify, widget, fit_table, observation_table, stability_plot, cross_table
from build_georg_fem_reports import table
from bei_breathing_overview import widget as bei_widget
contract = verify()

## Просмотр BEI на этапах дыхания

**Рисунок А.** Перед расчётом удельных сопротивлений показаны оба исходных импедансных поля
BEI всех 18 записей. В верхней панели можно сравнить кривые по времени,
в нижней — их медианы и разброс на каждом кандидатном этапе дыхания.
Выберите записи, BEI1 или BEI2, этап дыхания и шкалу кривых. Кнопка
«Пять размеров основного ряда» оставляет записи 004 и 007–010. Для проверки
конкретного выброса удобно снять общий выбор, включить одну запись и увеличить
нужный участок верхнего графика. Цвет соответствует записи; BEI1 показан
сплошными линиями и круглыми метками уровней, BEI2 — штриховыми линиями
и ромбами. Все поля сохраняют приборные номера; назначение бокового канала
по этому графику не определяется.

В режиме «Все этапы / вся запись» время отсчитывается от начала каждой
записи. При выборе одного этапа его кандидатное начало совмещается с нулём
времени; физическая длительность сохраняется. Записи получены последовательно,
поэтому совпадающая абсцисса не означает одновременность измерений.
Дыхательные границы и области их неоднозначности перенесены из 11.20
без изменения и пока не приняты автором. Цветной фон этапов и серые полосы
неоднозначности показаны при выборе одной записи. Запись 001 содержит только
кандидатный этап спокойного дыхания. Для записей 005 и 006 сохранён сценарий
400 Гц, для остальных — 1000 Гц; правильность этих временных шкал ещё требует
подтверждения. Вариант без разметки не получает вымышленных фаз.

По умолчанию показаны полные кандидатные этапы. Переключатель «Только интервалы
расчёта уровней 33.21» оставляет те же внутренние участки задержек, которые
использованы в обратной задаче: от неоднозначных границ отступают на 2 с,
от краёв записи — на 5 с. Поэтому медиана полного этапа может отличаться
от уровня в таблице 2; после включения расчётных интервалов уровни совпадают
для соответствующих записей и полей. Переключение не меняет разметку,
состав основного ряда или сохранённые расчётные оценки.

Исходный BEI показан в омах без фильтрации, вычитания тренда и удаления
выбросов. Альтернативная шкала вычитает медиану своего выбранного интервала
из каждого значения; это позволяет увидеть нисходящие отклонения при разных
абсолютных уровнях. Она не выделяет пульсовую составляющую. Этапы не соединяются
между собой, чтобы вычитание разных медиан не создавало ложного перехода.
Красные треугольники отмечают отображаемые значения ниже медианы на заданный
порог, по умолчанию 1 Ом. Это настраиваемый способ поиска кандидатов;
дыхательное изменение уровня также может попасть под него. Ни такая метка,
ни отрицательное отклонение от медианы сами по себе не доказывают дефект.

Для компактного изображения каждый выбранный интервал разбит не более чем
на 600 последовательных групп отсчётов; минимум и максимум каждой группы
сохранены в их исходные моменты времени. Крайние отсчёты и границы пропусков
тоже сохраняются. Такое прореживание удерживает одиночные экстремумы, но
не сохраняет полную форму и длительность каждого быстрого события; увеличение
масштаба не возвращает удалённые точки. Детальное решение о качестве следует
принимать по полным локальным массивам отсчётов, сохранённым на этапе 11.20.
Медианы, квартили,
экстремумы и числа отсчётов в нижней панели и таблице рассчитаны по всем
исходным значениям выбранного интервала.

В нижней панели вертикальные отрезки показывают минимум–максимум либо
квартили 25–75%; можно оставить только медианы. Это разброс значений внутри
интервала, а не погрешность измерения или доверительный интервал. Q25 и Q75
в таблице обозначают соответственно 25-й и 75-й процентили. В таблице
отдельно указаны число исходных значений ниже нуля и число неконечных
значений. Порог 1 Ом не применяется к этим счётчикам. Нулевой уровень выбранной
шкалы на верхнем графике обозначен чёрной точечной линией.

In [2]:
display(HTML(bei_widget()))

## Входы и границы расчёта

Непосредственно записаны два общих импедансных поля BEI, содержащих базовую
и пульсовую составляющие. Используются медианы исходного BEI в кандидатных
задержках на вдохе и выдохе из этапа 11.20. Новая разметка здесь не создаётся.
Интервалы ещё не приняты автором, поэтому численные результаты условны.

По окончательному уточнению автора от 09.10.2026 боковой размерный ряд
берётся из **BEI2 в 004** и **BEI1 в 007–010**. В 005 ТТРКГ — BEI1,
вертикальная боковая — BEI2; в 006 горизонтальная боковая — BEI1,
сохранённая вертикальная — BEI2. Для 011 назначение наследуется из 010.
Качество ЭКГ креста не используется для назначения его осей.
Продолжение нумерации после 007 принято по постоянству позднего блока
в описании протокола. Дыхательные интервалы остаются кандидатными.
Подробности и численные переходы приведены в
[10.30](10.30_Критическая_проверка_назначения_каналов_Scorpion_v2.html).

Первым показан пересчёт по этому назначению. Два прежних постоянных
сценария сохранены для сравнения с ошибочной нумерацией. Их минимумы
не используются вместо результата по подтверждённому переходу.
Для 001–003 автор подтвердил ТТРКГ1 и боковую горизонтальную BEI2.
Наблюдения 002–003 остаются дополнительными: они получены с другими
монтажами на руках и не входят в совместную подгонку основного ряда.
В 005 показано только боковое BEI2: ТТРКГ1 исключена из множества
боковых решений. Основная горизонтальная ось и вертикальная ось креста
различаются явно, независимо от номера канала.

Рабочие диапазоны взяты из [числового реестра свойств тканей](../../MATLAB_TRKG4_real_subjects/configs/tissue_literature_v2.json)
для профиля 100 кГц: **ρ₁ = 1,3774–41,6899 Ом·м**, **ρ₂ = 3,6817–24,0741 Ом·м**.
Первый диапазон относится к мягкотканному фону, второй — к обобщённому лёгкому.
Сводный реестр включает перенос низкочастотных литературных границ; эти
интервалы являются рабочим физиологически мотивированным ограничением,
а не индивидуально подтверждёнными нормами Георга. Расчётная толщина
**h = 0,5–100 мм** задаёт исследуемую область и пока не измерена по КТ.

По решению автора от 09.10.2026 эти ограничения применены к текущей обратной
задаче. Прежний поиск в технических пределах 0,1–100 Ом·м сохранён в
[архивной редакции](../archive/legacy/scorpion_v2/2026-10-09_e799fdb/33.21_Множество_решений_двуслойной_модели_Scorpion_v2.html).
Его граничные оценки не используются как рабочие параметры тканей.

Последовательно записанные размеры считаются сопоставимыми по состоянию
испытуемого. Вариабельность дыхания, контакта, установки и состояния между
записями не разделена и не заменяется одним условным уровнем шума.

## Прямая модель и поверхность одной сборки

Верхний слой имеет сопротивление ρ₁ и толщину h, нижний полубесконечный
слой — сопротивление ρ₂. В этой редукции отсутствуют отдельные рёбра,
жировой слой и сердце. Номинальная токовая база равна L, потенциальная — L/2;
контакты находятся в точках −L/2, −L/4, L/4, L/2. Все четыре контакта
представлены круглыми дисками диаметром 5 мм и площадью 19,635 мм².
Ток равномерно распределён по токовому диску, потенциал усредняется по
измерительному. Контактный импеданс и влияние одновременно подключённых
электродов других каналов в этой модели не представлены.

Линейность по общему масштабу сопротивлений позволяет записать:

$$q=\frac{\rho_2}{\rho_1},\qquad
Z_L(\rho_1,\rho_2,h)=\rho_1 f_L(q,h),\qquad
\rho_1=\frac{Z_L^{\mathrm{набл}}}{f_L(q,h)},\quad \rho_2=q\rho_1,$$

где q — безразмерный контраст сопротивлений; Z — передаточный импеданс в Ом;
f — ответ прямой модели на единичное сопротивление верхнего слоя, в м⁻¹;
L и h в вычислительной модели переведены в метры. При фиксированном h
последние два выражения задают кривую ρ₁(ρ₂), воспроизводящую одно наблюдение.
При изменении h эта кривая образует поверхность в пространстве (ρ₂, ρ₁, h).
На графиках оставлены только точки, удовлетворяющие обоим диапазонам тканей.

Для изображения используются 101 значение h и 481 значение q. Поверхности
визуально прорежены, кривые среза используют полную сетку q. Для каждой пары
разных размеров ищутся смены знака разности уравнений; корни уточняются
непосредственным расчётом дисковой модели. Остаток каждого парного уравнения
проверен подстановкой и не превышает 10⁻⁷ Ом. Касательные корни и ветви между
узлами сетки h могут быть пропущены.

Одинаковые номинальные размеры имеют одинаковую прямую модель. Если их
измеренные уровни различны, их поверхности не пересекаются; совпадение
уровней означало бы совпадение поверхностей. Ориентация в однородной плоской
модели ничего не меняет, поэтому расхождение осей креста нельзя объяснить
только её средствами.

## Три самостоятельных представления решений

**Рисунки 1–3.** У каждого графика собственные переключатели истории
подключения, дыхательного состояния, толщины, сборок и пересечений.
Настройки одного графика не меняют два других. Это позволяет одновременно
сравнивать разные состояния, варианты подключения и значения h.
Первый график показывает кривые ρ₁(ρ₂) при выбранном h на плоскости
сопротивлений. Второй показывает
поверхности и уточнённые попарные пересечения по всей сетке h. Третий —
двумерный срез при независимо выбранном h. На втором графике настройка h
задаёт только уровень отдельной переключаемой плоскости сечения;
поверхности охватывают всю сетку h. По умолчанию на всех графиках h = 20 мм; это иллюстративный
сценарий, а не выбранная по КТ толщина. Кнопки ← и → перебирают соседние
значения сетки h: 0,5 мм, затем 1–100 мм с шагом 1 мм. На границах области
соответствующая кнопка отключена. Масштаб и смещение плоских графиков,
а также камера трёхмерного графика сохраняются при изменении параметров. Выбор видимых сборок меняет
отображение; сохранённый совместный минимум всегда относится ко всему
основному ряду из пяти размеров и не пересчитывается по видимому подмножеству.

**Различие рисунков 1 и 3.** На рисунке 1 представлено решение уравнения
каждой сборки при фиксированном h; на рисунке 3 — сечение тех же поверхностей
решений плоскостью h = const. При одинаковых настройках это одно и то же
математическое множество, поэтому линии и метки совпадают. Срез строится
по исходным уравнениям на полной сетке q, без интерполяции прореженного
трёхмерного изображения. Два плоских графика сохранены с независимыми
настройками для сравнения разных h, дыхательных состояний или гипотез
подключения. Они не являются независимыми подтверждениями модели.

Основной ряд включает пять размеров 60–140 мм с монтажом ТТРКГ 1×4.
Дополнительно показаны боковые наблюдения 140 мм при 1×1
и 2×2 на руках, вертикальная BEI2 записи 005 и обе оси крестов 140 и 60 мм.
BEI1 записи 005 не включается: по уточнению автора это ТТРКГ.
Дополнительные наблюдения служат проверкой и не участвуют в совместной
подгонке основного ряда.

**Обозначения на рисунках 1–3.** Цвет соответствует конкретному наблюдению;
таким же цветом подписан его переключатель. Каждая линия воспроизводит
уровень импеданса одной сборки в пределах принятых диапазонов сопротивлений.
Она не является доверительной границей или траекторией изменения ткани.

- Сплошные более толстые линии на рисунках 1 и 3 относятся к пяти размерам
  основного ряда, использованным в совместной подгонке. Штриховые более
  тонкие линии — к дополнительным наблюдениям, использованным для проверки.
- Чёрные круглые метки удовлетворяют двум уравнениям соответствующей пары.
  На плоских графиках показаны пересечения при выбранном h, на рисунке 2 —
  по всей сетке h. При наведении указаны пара и максимальное расхождение
  с пятью основными наблюдениями. Попарное пересечение не доказывает
  существования общего решения для всех сборок.
- Красный круг на рисунках 1 и 3 — сеточный минимум суммы квадратов невязок
  пяти основных размеров при фиксированном h. Он обычно не лежит одновременно
  на всех линиях и не является точным решением каждого уравнения.
- Красный ромб на рисунке 2 — совместный минимум той же суммы при подборе
  всех трёх параметров ρ₁, ρ₂ и h. Это сохранённый результат полной подгонки,
  который не изменяется при скрытии отдельных наблюдений.
- Цветные полупрозрачные поверхности на рисунке 2 объединяют решения каждой
  сборки при разных h. Светло-серая плоскость показывает выбранный уровень h;
  её площадь не означает допустимость решений во всех точках этой плоскости.

Минимумы невязки относятся ко всему основному ряду даже при его частичном
скрытии. Формула суммы квадратов невязок приведена ниже.

In [3]:
display(HTML(widget()))

## Совместная оценка пяти размеров в рабочих диапазонах

Оптимизируются три положительных параметра по пяти наблюдениям одного
дыхательного состояния и одной истории подключения:

$$\mathrm{RSS}=\sum_{L}(Z_L^{\mathrm{мод}}-Z_L^{\mathrm{набл}})^2,\qquad
\varepsilon=100\frac{\sqrt{\mathrm{RSS}}}{\sqrt{\sum_L (Z_L^{\mathrm{набл}})^2}},$$

где RSS — сумма квадратов невязок в Ом², ε — относительная невязка в процентах.
Равные веса отражают отсутствие установленной дисперсии ошибок каждого
наблюдения; они не являются подтверждённой моделью измерительной погрешности.

**Таблица 1.** Минимумы в рабочих диапазонах и параметры, достигшие границ.

In [4]:
display(table(fit_table()))

История подключения,Дыхание,"ρ₁, Ом·м","ρ₂, Ом·м","h, мм","Относительная невязка, %",Параметры на границе,κ(J) по логарифмам параметров
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,"1,3774","18,599","2,2636","10,536",ρ₁,8120
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Выдох,"1,3774","18,116","2,217","9,7445",ρ₁,"8158,6"
Прежний сценарий: постоянно BEI1,Вдох,"1,3774","15,432","1,8897","11,558",ρ₁,"8988,8"
Прежний сценарий: постоянно BEI1,Выдох,"1,3774","14,921","1,8164","10,911",ρ₁,"9316,9"
Прежний сценарий: постоянно BEI2,Вдох,"1,3774","24,074","5,1223","15,171","ρ₁, ρ₂","1867,1"
Прежний сценарий: постоянно BEI2,Выдох,"1,3774","24,074","5,2421","15,516","ρ₁, ρ₂","1697,3"


Для подтверждённого перехода относительная невязка составляет
10,54% на вдохе и 9,74% на выдохе. Условные минимумы равны
(ρ₁, ρ₂, h) = (1,3774 Ом·м; 18,5989 Ом·м; 2,2636 мм) на вдохе
и (1,3774 Ом·м; 18,1160 Ом·м; 2,2170 мм) на выдохе.
В обоих случаях ρ₁ достигает нижней границы. Эти оценки отражают
минимум данной модели и не являются измеренными параметрами тканей;
вычисленная h не установлена как анатомическая толщина по КТ.

Для прежних постоянных сценариев невязки составляют 11,56 и 10,91%
при BEI1; 15,17 и 15,52% при BEI2. Ограничение диапазонов и исправление
назначения улучшают согласие, но не дают внутреннего устойчивого минимума.
Граничные оценки пока нельзя передавать далее как определённые свойства тканей.

Неустановленная суммарная погрешность не позволяет формально отвергнуть
модель по статистическому критерию. Граничный минимум и чувствительность
параметров требуют индивидуальной КТ/FEM-проверки.

Число обусловленности κ(J) в таблице получено из отношения наибольшего
и наименьшего сингулярных чисел матрицы производных пяти импедансов по
логарифмам ρ₁, ρ₂ и h. Большие значения означают слабую различимость изменений
параметров в локальной линеаризации. У граничного минимума этот показатель
не является доверительным интервалом и не учитывает ограничения оптимизации.

**Рисунок 4.** Профиль минимальной невязки при фиксированной h в тех же
диапазонах сопротивлений. Сплошные цветные линии относятся к шести
сочетаниям истории подключения и дыхательного состояния, указанным в легенде.
Минимизация по q выполнена на сетке; горизонтальная точечная линия на уровне
1,10 задаёт условный допуск 10% к RSS и не имеет статистической интерпретации.

In [5]:
display(HTML(stability_plot()))

"Сплошная линия: Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010, вдох","Минимум RSS по ρ₁ и ρ₂ при каждом h, делённый на совместный минимум RSS этого сценария."
"Сплошная линия: Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010, выдох","Минимум RSS по ρ₁ и ρ₂ при каждом h, делённый на совместный минимум RSS этого сценария."
"Сплошная линия: Прежний сценарий: постоянно BEI1, вдох","Минимум RSS по ρ₁ и ρ₂ при каждом h, делённый на совместный минимум RSS этого сценария."
"Сплошная линия: Прежний сценарий: постоянно BEI1, выдох","Минимум RSS по ρ₁ и ρ₂ при каждом h, делённый на совместный минимум RSS этого сценария."
"Сплошная линия: Прежний сценарий: постоянно BEI2, вдох","Минимум RSS по ρ₁ и ρ₂ при каждом h, делённый на совместный минимум RSS этого сценария."
"Сплошная линия: Прежний сценарий: постоянно BEI2, выдох","Минимум RSS по ρ₁ и ρ₂ при каждом h, делённый на совместный минимум RSS этого сценария."
"Серая точечная горизонталь 1,10",Условный прирост RSS на 10%; не доверительная граница и не критерий физиологической достоверности.


## Повторы 140 мм и оси креста

**Таблица 2.** Уровни всех отображаемых боковых наблюдений. Номера записей
соответствуют [реестру эксперимента](../../Experiments/scorpion_v2_georg/RECORDINGS.md).
При переключении истории меняется выбранное поле основного ряда,
но не измеренные значения каждого поля. Сравнение повторов 140 мм нужно
проводить внутри одной истории подключения и одного дыхательного состояния.

In [6]:
display(table(observation_table()))

История подключения,Дыхание,Сборка и запись,Поле BEI,"Медиана Z, Ом",Основной размерный ряд
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,60 мм · 010 · основной ряд,1,"115,33",Да
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,80 мм · 009 · основной ряд,1,"127,83",Да
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,100 мм · 008 · основной ряд,1,"85,702",Да
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,120 мм · 007 · основной ряд,1,"86,24",Да
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,140 мм · 004 · основной ряд,2,"79,595",Да
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,140 мм · 002 · 1×1 на руках · дополнительное наблюдение,2,"79,427",Нет
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,140 мм · 003 · 2×2 на руках · дополнительное наблюдение,2,"80,953",Нет
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,"140 мм · 005 · вертикальная боковая, BEI2",2,"75,98",Нет
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,140 мм · 006 · горизонтальная ось креста,1,"76,818",Нет
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,140 мм · 006 · вертикальная ось креста,2,"81,515",Нет


**Таблица 3.** Повторная подгонка с заменой единственного наблюдения
140 мм на основную ось креста. Дополнительно показан один и тот же прогноз
140 мм по четырём размерам 60–120 мм: он рассчитан без обоих проверяемых
наблюдений 140 мм. Замена служит диагностикой и не означает принятия записи
или изменения основного размерного ряда.

In [7]:
display(table(cross_table()))

История подключения,Дыхание,Вариант 140 мм,"Z₁₄₀, Ом","Прогноз 140 мм по 60–120 мм, Ом","Ошибка прогноза, Ом","Невязка пяти размеров, %"
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,"Основной ряд, запись 004","79,595","79,369","−0,22648","10,536"
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Вдох,"Горизонтальная ось креста, запись 006","76,818","79,369","2,5512","10,616"
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Выдох,"Основной ряд, запись 004","79,095","78,52","−0,57519","9,7445"
Подтверждённый переход: BEI2 в 004 → BEI1 в 007–010,Выдох,"Горизонтальная ось креста, запись 006","75,932","78,52","2,5878","9,8301"
Прежний сценарий: постоянно BEI1,Вдох,"Основной ряд, запись 004","67,018","79,369","12,35","11,558"
Прежний сценарий: постоянно BEI1,Вдох,"Горизонтальная ось креста, запись 006","76,818","79,369","2,5512","10,616"
Прежний сценарий: постоянно BEI1,Выдох,"Основной ряд, запись 004","65,645","78,52","12,875","10,911"
Прежний сценарий: постоянно BEI1,Выдох,"Горизонтальная ось креста, запись 006","75,932","78,52","2,5878","9,8301"
Прежний сценарий: постоянно BEI2,Вдох,"Основной ряд, запись 004","79,595","56,349","−23,247","15,171"
Прежний сценарий: постоянно BEI2,Вдох,"Горизонтальная ось креста, запись 006","81,515","56,349","−25,166","16,178"


При подтверждённом назначении основной уровень 140 мм в 004
ближе к прогнозу по 60–120 мм: абсолютная ошибка равна 0,23 Ом на вдохе
и 0,58 Ом на выдохе. Для горизонтальной оси креста 006 ошибки равны
2,55 и 2,59 Ом. Замена 004 на крест увеличивает совместную невязку
с 10,54 до 10,62% на вдохе и с 9,74 до 9,83% на выдохе.
Следовательно, прежний вывод об улучшении при замене на крест зависел
от ошибочного выбора BEI1 для 004. Подтверждённое назначение устраняет
этот вывод, но не устраняет расхождения остального размерного ряда.

Изменение одного уровня 140 мм меняет геометрию совместного пересечения,
но само по себе не устанавливает правильность установки или пригодность модели.
На одинаковом L плоская модель не различает основной и крестообразный монтаж,
влияние соседней сборки и анатомическую ориентацию. Эти различия должны быть
проверены в индивидуальной модели, а не компенсированы изменением ρ.

Резкие изменения условных сопротивлений при некоторых h отражают обращение
слабо чувствительной модели: малое изменение импеданса может требовать
большого изменения параметра. За пределами рабочего диапазона такая ветвь
обрезана, а отсутствие кривой на выбранном h означает, что допустимые решения
не найдены на используемой сетке q. Межузловые ветви этим не исключены.
Это не свидетельство скачка сопротивления ткани.

## Дальнейшая проверка

Следующий расчёт использует [исправленную геометрию КТ](20.20_Индивидуальная_КТ_FEM_модель_Георгия_Scorpion_v2.html):
полное соединение цилиндров рук с телом, продольные боковые сборки и
верхние/нижние токовые контакты. Нужно исследовать все допустимые положения
общего центра, сегменты сердца, лёгких, костей и жира, конечные площади
электродов и чувствительности к сопротивлениям каждого компартмента.
Анатомическая толщина и электрически эквивалентная h требуют отдельного
правила сопоставления. Историческая FEM-инверсия 33.22 выполнена на прежней
геометрии и не заменяет этот перерасчёт.

До его завершения не выбрана оптимальная пара сборок, не определены
поправки к ТТРКГ и не получены валидированные УО и ФВ. Сохранённые поверхности
показывают структуру обратной задачи и её ограничения.